In [4]:
from DataInput import DataStream
import requests
import json

In [7]:
data_stream = DataStream()

base_url = "https://tld.iot.hamburg.de/v1.1/Datastreams"
params = {
    "$filter": "properties/layerName eq 'primary_signal'",
    "$expand": "Thing($expand=Locations)",
    "$top": 1000,
}

all_datastreams = []

while True:
    # print("hi")
    response = requests.get(base_url, params=params)
    if response.status_code == 200:
        data = response.json()
        all_datastreams.extend(data.get("value", []))
        next_link = data.get("@iot.nextLink")
        if next_link:
            base_url = next_link
        else:
            break
    else:
        print(f"Error: {response.status_code} - {response.text}")
        break

print(f"Retrieved {len(all_datastreams)} datastreams.")

Retrieved 19969 datastreams.


In [47]:
first_stream = all_datastreams[0]
print(json.dumps(first_stream, indent=4))

{
    "@iot.selfLink": "https://tld.iot.hamburg.de/v1.1/Datastreams(45434)",
    "@iot.id": 45434,
    "name": "Primary signal heads at 248_25",
    "description": "Datastream to broadcast the lane connection's signal value of a signal group",
    "observationType": "http://www.opengis.net/def/ogc-om/OM_CategoryObservation",
    "unitOfMeasurement": {
        "name": "Signal Status ",
        "symbol": "\"[0-6,9]\"",
        "definition": "0=dark,1=red,2=amber,3=green,4=red-amber,5=amber-flashing,6=green-flashing,9=unknown"
    },
    "observedArea": {
        "type": "Point",
        "coordinates": [
            10.0129167,
            53.5898999
        ]
    },
    "phenomenonTime": "2007-08-30T22:02:28Z/2024-10-21T09:06:23Z",
    "properties": {
        "metadata": "https://registry.gdi-de.org/id/de.hh/fa5588ec-bc36-4070-8871-6bf69365fe79",
        "layerName": "primary_signal",
        "ownerData": "Free and Hanseatic City of Hamburg",
        "serviceName": "HH_STA_traffic_lights

In [32]:
results = dict()

for stream in all_datastreams:
    if "observedArea" not in stream.keys():
        if "noObservedArea" not in results:
            results["noObservedArea"] = 0
        results["noObservedArea"] += 1
    else:
        type = stream["observedArea"]["type"]
        if type not in results:
            results[type] = 0
        results[type] += 1
print(results)
print(sum([value for _, value in results.items()]))

{'Point': 9178, 'LineString': 9489, 'Polygon': 1111, 'noObservedArea': 191}
19969


In [2]:
import pickle
import copy

datastream_copy = copy.deepcopy(all_datastreams)

with open("datastreams1.pkl", "wb") as file:
    pickle.dump(data_stream, file)

print("Saved successfully!")

Saved successfully!


In [34]:
import folium
from IPython.display import display


def switch_coords(coords):
    temp = coords[0]
    coords[0] = coords[1]
    coords[1] = temp


# save possible colors for markers
colors = [
    "red",
    "blue",
    "green",
    "purple",
    "orange",
    "darkred",
    "lightred",
    "beige",
    "darkblue",
    "darkgreen",
    "cadetblue",
    "darkpurple",
    "white",
    "pink",
    "lightblue",
    "lightgreen",
    "gray",
    "black",
]


def create_marker(coords, color_index):
    folium.CircleMarker(
        location=coords,
        radius=1,
        color=colors[color_index],
        fill=True,
        fill_color=colors[color_index],
        opacity=1,
    ).add_to(map_object)


# define starting point for map (chosen arbitrarily)
hamburg_mid_point = [53.571974, 9.969119]

# create maps
map_object = folium.Map(location=hamburg_mid_point, zoom_start=12)


counter = 0
for stream in all_datastreams:
    if "observedArea" not in stream.keys():
        continue

    if stream["observedArea"]["type"] == "Point":
        coords = stream["observedArea"]["coordinates"]
        switch_coords(coords)
        create_marker(coords, 0)
    elif stream["observedArea"]["type"] == "LineString":
        coord_pairs = stream["observedArea"]["coordinates"]
        for coords in coord_pairs:
            switch_coords(
                coords
            )  # latidute and longitude are given switch up by the API
            # add Marker for each coordinate_pair
            create_marker(coords, 1)
    else:
        coord_pairs = stream["observedArea"]["coordinates"][0]
        for coords in coord_pairs:
            switch_coords(
                coords
            )  # latidute and longitude are given switch up by the API
            create_marker(coords, 2)

# Display the map
display(map_object)